# Access to jobs by public transport in Montevideo

This report examines the percentage of jobs that residents can reach within 15, 30, and 45 minutes by public transport and walking. It serves a baseline to identify gaps in job access geographically and for planning future public transit. 

In [1]:
from pathlib import Path

import altair as alt
import attaviz
import contextily as cx
import geopandas as gpd
import pandas as pd
from IPython.display import display

attaviz.enable()


def find_project_root(marker="pyproject.toml"):
    current = Path.cwd()
    for parent in [current, *current.parents]:
        if (parent / marker).exists():
            return parent
    raise FileNotFoundError(f"Could not find {marker}")


def simplify_for_web(frame, tolerance=30):
    """Simplify projected geometry for maps without changing its extent."""
    display_frame = frame.to_crs(LOCAL_CRS).copy()
    display_frame.geometry = display_frame.geometry.simplify(
        tolerance, preserve_topology=True
    )
    return display_frame.to_crs(WGS84_CRS)


def show_full_extent(map_object):
    """Keep the map's automatic bounds so full geometries remain visible."""
    return map_object


PROJECT_ROOT = find_project_root()
DATA_PATH = PROJECT_ROOT / "data"
POPULATION_PATH = DATA_PATH / "population" / "poblacion-zonificacion.gpkg"
EMPLOYMENT_PATH = DATA_PATH / "URY_montevideo_employment_predictions_relative.gpkg"
BARRIOS_PATH = DATA_PATH / "geography-levels" / "barrios_mvd_23_pg.gpkg"
SECTIONS_PATH = DATA_PATH / "geography-levels" / "sc_23_pg.gpkg"
OUTPUT_PATH = DATA_PATH / "opportunities"
POPULATION_MATRIX_PATH = OUTPUT_PATH / "accessibility_wed_08.parquet"

TILES = cx.providers.Esri.WorldGrayCanvas
LOCAL_CRS = "EPSG:32721"
WGS84_CRS = "EPSG:4326"
THRESHOLDS = (15, 30, 45)
DISPLAY_THRESHOLD = 30
SCENARIOS = (
    "wed_07",
    "wed_08",
    "wed_09",
    "wed_10",
    "sat_07",
    "sat_08",
    "sat_09",
    "sat_10",
)

SCENARIO_METADATA = (
    pd.DataFrame(
        [
            {
                "scenario": "wed_07",
                "departure_date": "2026-03-25",
                "departure_time": "07:00",
            },
            {
                "scenario": "wed_08",
                "departure_date": "2026-03-25",
                "departure_time": "08:00",
            },
            {
                "scenario": "wed_09",
                "departure_date": "2026-03-25",
                "departure_time": "09:00",
            },
            {
                "scenario": "wed_10",
                "departure_date": "2026-03-25",
                "departure_time": "10:00",
            },
            {
                "scenario": "sat_07",
                "departure_date": "2026-03-28",
                "departure_time": "07:00",
            },
            {
                "scenario": "sat_08",
                "departure_date": "2026-03-28",
                "departure_time": "08:00",
            },
            {
                "scenario": "sat_09",
                "departure_date": "2026-03-28",
                "departure_time": "09:00",
            },
            {
                "scenario": "sat_10",
                "departure_date": "2026-03-28",
                "departure_time": "10:00",
            },
        ]
    )
    .set_index("scenario")
    .loc[list(SCENARIOS)]
    .reset_index()
)
ROUTING_PARAMETERS = {
    "transport_modes": "TRANSIT + WALK",
    "departure_window_minutes": 60,
    "percentile": "p50",
    "snap_to_network_m": 1600,
    "max_time_minutes": 120,
    "max_time_walking_minutes": 120,
}


## Data sources

| Dataset | Details |
|---|---|
| Population zoning | `poblacion-zonificacion.gpkg`: source population and zone polygons |
| Employment grid | `URY_montevideo_employment_predictions_relative.gpkg` destination hexagons and job shares |
| Neighborhoods | `barrios_mvd_23_pg.gpkg`: `CODBARRIOINE` and `NOMBARRIOINE` |
| Census sections | `sc_23_pg.gpkg`: `CODSECC` and `section_label` |
| Baseline matrix | `accessibility_wed_08.parquet`: population-zone origins to employment hexagons |
| Scenario matrices | `accessibility_{scenario}.parquet`: population-zone origins to employment hexagons at each departure scenario |
| Hexagon matrices | `accessibility_grid_{scenario}.parquet`: employment-hexagon-origin and destinations at each departure scenario |


### Clip the project zones to match the jobs layer. 
The area of interest for the entire project is larger than the jobs layer. For this reason, we ar

In [2]:
population_zones = (
    gpd.read_file(POPULATION_PATH)
    .rename(columns={"id_poligono": "zone_id", "poblacion": "population"})
    .to_crs(LOCAL_CRS)
)
employment_grid = gpd.read_file(EMPLOYMENT_PATH)
employment_grid_local = employment_grid.to_crs(LOCAL_CRS)

# The employment-layer union is the sole analysis boundary. It is also the
# inclusion boundary for the report.
analysis_boundary = employment_grid_local.geometry.union_all()
jobs_bounds_wgs84 = employment_grid.to_crs(WGS84_CRS).total_bounds
JOBS_BOUNDS_LATLON = [
    [float(jobs_bounds_wgs84[1]), float(jobs_bounds_wgs84[0])],
    [float(jobs_bounds_wgs84[3]), float(jobs_bounds_wgs84[2])],
]

# A source zone is included when its overlap with the jobs layer has positive area.
population_zones["zone_area_m2"] = population_zones.geometry.area
in_scope_geometry = population_zones.geometry.intersection(analysis_boundary)
population_zones["in_scope_area_m2"] = in_scope_geometry.area

# Consider only polygons that are almost entirely covered by the analysis boundary
population_zones['percentage_covered'] = population_zones['in_scope_area_m2'] / population_zones['zone_area_m2']

project_zones = population_zones.loc[population_zones["percentage_covered"] > 0.9].copy()
# Unsure why we need this
# project_zones["population_outside_jobs_layer"] = project_zones["population"] * (
#     1 - project_zones["in_scope_area_m2"] / project_zones["zone_area_m2"]
# )
project_zones["population_density_per_km2"] = project_zones["population"] / (
    project_zones["zone_area_m2"] / 1_000_000
)
project_zone_ids = set(project_zones["zone_id"])

#Once we clipped then project zones/population, we do not need what there is outside of it. 
data_inventory = pd.DataFrame(
    {
        "dataset": [
            # "Population source",
            "Included source-zone population",
            "Employment grid",
        ],
        # "records": [len(population_zones), len(project_zones), len(employment_grid)],
        "records": [len(project_zones), len(employment_grid)],
        "crs": [
            # population_zones.crs.to_string(),
            project_zones.crs.to_string(),
            employment_grid.crs.to_string(),
        ],
        "geometry": [
            # population_zones.geometry.geom_type.mode().iat[0],
            project_zones.geometry.geom_type.mode().iat[0],
            employment_grid.geometry.geom_type.mode().iat[0],
        ],
        "fields": [
            # ", ".join(population_zones.columns.drop("geometry")),
            ", ".join(project_zones.columns.drop("geometry")),
            ", ".join(employment_grid.columns.drop("geometry")),
        ],
    }
)
data_inventory


,dataset,records,crs,geometry,fields
0,Included source-zone population,467,EPSG:32721,Polygon,"zone_id, tipo_zona, population, zone_area_m2, ..."
1,Employment grid,3808,EPSG:4326,MultiPolygon,"grid_id, pred_relative_employment"


## Where people and jobs are located

A population zone is included if its polygon intersects the employment hexagons, while a zone with no overlap is excluded. Included zones retain their full geometry and population. The employment layer itself provides the job share for each hexagon. The values sum to 100% across the layer, so job accessibility is reported as a percentage of jobs rather than as a count.


In [3]:
population_zone_summary = (
    project_zones.assign(population_missing=project_zones["population"].isna())
    .groupby("tipo_zona", dropna=False)
    .agg(
        zone_count=("zone_id", "size"),
        jobs_overlap_area_km2=(
            "in_scope_area_m2",
            lambda values: values.sum() / 1_000_000,
        ),
        population=("population", "sum"),
        # population_outside_jobs_layer=("population_outside_jobs_layer", "sum"),
        missing_population=("population_missing", "sum"),
    )
    .reset_index()
)
# print(
#     f"Full-zone population denominator: "
#     f"{project_zones['population'].sum():,.1f} people across "
#     f"{project_zones['population'].notna().sum():,} zones"
# )
# display(population_zone_summary.round(2))

# population_context_map = show_full_extent(
#     simplify_for_web(project_zones).explore(
#         column="population",
#         cmap="Blues",
#         legend=True,
#         scheme="Quantiles",
#         k=5,
#         tooltip=[
#             "zone_id",
#             "tipo_zona",
#             "population",
#             # "in_scope_area_m2", # we could add the zone area itself
#             # "population_outside_jobs_layer",
#         ],
#         tiles=TILES,
#         legend_kwds={"caption": "Población"},
#         style_kwds={"weight": 0.4, "color": "white", "fillOpacity": 0.75},
#         missing_kwds={"color": "lightgrey", "label": "Sin Población"},
#     )
# )
# display(population_context_map)

population_density_map = show_full_extent(
    simplify_for_web(project_zones).explore(
        column="population_density_per_km2",
        cmap="YlGnBu",
        legend=True,
        scheme="Quantiles",
        k=5,
        tooltip=[
            "zone_id",
            "population",
            # "in_scope_area_m2",
            # "population_outside_jobs_layer",
            "population_density_per_km2",
        ],
        tiles=TILES,
        legend_kwds={"caption": "Densidad poblacional (personas/km²)"},
        style_kwds={"weight": 0.4, "color": "white", "fillOpacity": 0.75},
        missing_kwds={"color": "lightgrey", "label": "Sin Población"},
    )
)
display(population_density_map)

employment_context_map = show_full_extent(
    simplify_for_web(employment_grid, tolerance=20).explore(
        column="pred_relative_employment",
        cmap="Purples",
        legend=True,
        scheme="Quantiles",
        k=5,
        tooltip=["grid_id", "pred_relative_employment"],
        tiles=TILES,
        legend_kwds={"caption": "Share of jobs (percentage points)"},
        style_kwds={"weight": 0.2, "color": "#756bb1", "fillOpacity": 0.75},
    )
)
display(employment_context_map)


## How accessibility is measured

For each project zone or jobs-layer hexagon, accessibility is calculated by the sum of the job share in destination hexagons whose existing median (`p50`) travel time at 8 am on a Wednesday is below 15, 30, or 45 minutes.

In [4]:
if not POPULATION_MATRIX_PATH.exists():
    raise FileNotFoundError(
        f"Existing baseline matrix is missing: {POPULATION_MATRIX_PATH}"
    )

population_matrix = pd.read_parquet(POPULATION_MATRIX_PATH)
required_matrix_columns = {"from_id", "to_id", "p50"}
missing_matrix_columns = required_matrix_columns.difference(population_matrix.columns)
if missing_matrix_columns:
    raise ValueError(
        "Baseline matrix is missing columns: "
        + ", ".join(sorted(missing_matrix_columns))
    )

destination_ids_without_matrix_rows = sorted(
    set(employment_grid["grid_id"]) - set(population_matrix["to_id"])
)

matrix_summary = pd.DataFrame(
    {
        "measure": [
            "origin-destination pairs",
            "origins",
            "destinations",
            "employment hexagons without destination rows",
            "non-null p50 pairs",
        ],
        "value": [
            len(population_matrix),
            population_matrix["from_id"].nunique(),
            population_matrix["to_id"].nunique(),
            len(destination_ids_without_matrix_rows),
            population_matrix["p50"].notna().sum(),
        ],
    }
)
matrix_summary


,measure,value
0,origin-destination pairs,2104165
1,origins,553
2,destinations,3805
3,employment hexagons without destination rows,3
4,non-null p50 pairs,1556749


### Accessibility calculation

For origin *i*, destination hexagon *j*, and threshold *t* in `{15, 30, 45}`:

$$
A_i(t)
=
\sum_j \left[
\mathrm{job\_share}_j
\times
\mathbf{1}\!\left(\mathrm{p50}_{ij} \leq t\right)
\right]
$$

The population-weighted result uses the full population of each source zone:

$$
A_{\mathrm{population}}(t)
=
\frac{\sum_i \left[\mathrm{population}_i \times A_i(t)\right]}
     {\sum_i \mathrm{population}_i}
$$


## Routing coverage semantics

The coverage table and map distinguish three cases for every included source-zone origin:

- `Valid route within matrix horizon`: At least one matrix row has a non-null `p50`. Accessibility is measured from the available routed destinations.
- `No destination within matrix horizon`: Matrix rows exist, but every `p50` is null. Accessibility is explicitly zero for all three thresholds.
- `Origin missing from matrix`: no origin-destination rows exist. Accessibility remains missing rather than being silently treated as a measured zero.

In [5]:
def accessibility_scores(matrix):
    """Return job-share accessibility columns for every matrix origin."""
    pairs = matrix.merge(
        employment_grid[["grid_id", "pred_relative_employment"]],
        left_on="to_id",
        right_on="grid_id",
        how="left",
        validate="many_to_one",
    )
    score_columns = [f"accessibility_{minutes}min" for minutes in THRESHOLDS]
    scored_pairs = pairs.assign(
        **{
            f"accessibility_{minutes}min": pairs["pred_relative_employment"]
            .fillna(0)
            .where(pairs["p50"].le(minutes), 0)
            for minutes in THRESHOLDS
        }
    )
    return scored_pairs.groupby("from_id", as_index=False)[score_columns].sum()


def routing_coverage(matrix, origin_ids):
    """Classify matrix-row coverage without collapsing missing origins to zero."""
    matrix_coverage = (
        matrix.groupby("from_id")["p50"]
        .agg(
            matrix_rows="size",
            routed_pairs=lambda values: values.notna().sum(),
            has_any_route=lambda values: values.notna().any(),
        )
        .rename_axis("origin_id")
        .reset_index()
    )
    coverage = pd.DataFrame({"origin_id": list(origin_ids)}).merge(
        matrix_coverage, on="origin_id", how="left"
    )
    coverage["matrix_row_coverage"] = coverage["matrix_rows"].notna()
    coverage["has_any_route"] = coverage["has_any_route"].fillna(False).astype(bool)
    coverage["routing_status"] = "Origin missing from matrix"
    coverage.loc[
        coverage["matrix_row_coverage"] & ~coverage["has_any_route"],
        "routing_status",
    ] = "No destination within matrix horizon"
    coverage.loc[coverage["has_any_route"], "routing_status"] = (
        "Valid route within matrix horizon"
    )
    return coverage


def weighted_accessibility(frame, population_column="population"):
    """Return conservative and routed-denominator weighted job accessibility."""
    populated = frame[population_column].notna()
    routed = populated & frame["has_any_route"]
    denominator = frame.loc[populated, population_column].sum()
    routed_denominator = frame.loc[routed, population_column].sum()
    results = {
        "population_denominator": denominator,
        "routed_population_denominator": routed_denominator,
    }
    for minutes in THRESHOLDS:
        column = f"accessibility_{minutes}min"
        results[f"accessibility_{minutes}min_pct"] = (
            frame.loc[populated, population_column]
            * frame.loc[populated, column].fillna(0)
        ).sum() / denominator
        results[f"routed_accessibility_{minutes}min_pct"] = (
            frame.loc[routed, population_column] * frame.loc[routed, column]
        ).sum() / routed_denominator
    return results


In [6]:
zone_matrix = population_matrix.loc[
    population_matrix["from_id"].isin(project_zone_ids)
].copy()
zone_scores = accessibility_scores(zone_matrix).rename(columns={"from_id": "zone_id"})
zone_coverage = routing_coverage(zone_matrix, project_zones["zone_id"].tolist()).rename(
    columns={"origin_id": "zone_id"}
)
report_coverage = project_zones[
    ["zone_id", "tipo_zona", "population", "in_scope_area_m2"]
].merge(zone_coverage, on="zone_id", how="left")
project_zone_accessibility = project_zones.merge(zone_scores, on="zone_id", how="left")
project_zone_accessibility = project_zone_accessibility.merge(
    report_coverage[
        [
            "zone_id",
            "matrix_rows",
            "routed_pairs",
            "matrix_row_coverage",
            "has_any_route",
            "routing_status",
        ]
    ],
    on="zone_id",
    how="left",
)

In [7]:
baseline_metrics = weighted_accessibility(project_zone_accessibility)
report_results = pd.DataFrame(
    [
        {
            "threshold_minutes": minutes,
            "jobs_reachable_pct": baseline_metrics[f"accessibility_{minutes}min_pct"],
            "routed_population_jobs_reachable_pct": baseline_metrics[
                f"routed_accessibility_{minutes}min_pct"
            ],
            "population_denominator": baseline_metrics["population_denominator"],
            "routed_population_denominator": baseline_metrics[
                "routed_population_denominator"
            ],
        }
        for minutes in THRESHOLDS
    ]
)

report_results.round(2)

,threshold_minutes,jobs_reachable_pct,routed_population_jobs_reachable_pct,population_denominator,routed_population_denominator
0,15,2.07,2.07,1640198.0,1640198.0
1,30,15.34,15.34,1640198.0,1640198.0
2,45,38.51,38.51,1640198.0,1640198.0


In [8]:
# I think that we do not need this report now? 



# report_coverage_valid = report_coverage["population"].notna()
# report_coverage_summary = pd.DataFrame(
#     {
#         "metric": [
#             "Full-zone population denominator",
#             "Full-zone population with at least one non-null route",
#             "Full-zone population with zero route coverage",
#             "Full-zone population with missing origin rows",
#             "Project zones with at least one non-null route",
#             "Project zones with zero route coverage",
#             "Project zones missing from matrix",
#         ],
#         "value": [
#             report_coverage.loc[report_coverage_valid, "population"].sum(),
#             report_coverage.loc[
#                 report_coverage_valid & report_coverage["has_any_route"],
#                 "population",
#             ].sum(),
#             report_coverage.loc[
#                 report_coverage_valid
#                 & report_coverage["matrix_row_coverage"]
#                 & ~report_coverage["has_any_route"],
#                 "population",
#             ].sum(),
#             report_coverage.loc[
#                 report_coverage_valid & ~report_coverage["matrix_row_coverage"],
#                 "population",
#             ].sum(),
#             report_coverage["has_any_route"].sum(),
#             (
#                 report_coverage["matrix_row_coverage"]
#                 & ~report_coverage["has_any_route"]
#             ).sum(),
#             (~report_coverage["matrix_row_coverage"]).sum(),
#         ],
#     }
# )
# report_missing_origin_ids = report_coverage.loc[
#     ~report_coverage["matrix_row_coverage"], "zone_id"
# ].tolist()
# # print("Project-zone origins missing from matrix:", report_missing_origin_ids)
# # display(report_coverage_summary.round(2))

# coverage_map = project_zones.merge(
#     report_coverage[["zone_id", "routing_status"]], on="zone_id", how="left"
# )
# coverage_map["coverage_status"] = coverage_map["routing_status"]
# coverage_explore = show_full_extent(
#     simplify_for_web(coverage_map).explore(
#         column="coverage_status",
#         categorical=True,
#         cmap=["#238bce", "#de2d26", "#fdae6b"],
#         tooltip=[
#             "zone_id",
#             "tipo_zona",
#             "population",
#             "coverage_status",
#         ],
#         tiles=TILES,
#         legend_kwds={"caption": "Project-zone routing status"},
#         style_kwds={"weight": 0.4, "color": "white", "fillOpacity": 0.75},
#     )
# )
# coverage_explore


## How many jobs can residents reach?

The Wednesday 08:00 baseline is summarized in previous table for 15, 30, and 45 minutes. The denominator is the full reported population of source zones that overlap the jobs layer. The table includes both a conservative all-population result, where missing origin rows contribute zero only for aggregation, and a routed-population result restricted to origins with at least one non-null route.

The zone map below displays the 30-minute value for origins with a valid route. The separate coverage map identifies measured zeros and missing origins.

Interpretation: the headline preserves the full-zone denominator for included source zones, while the routed-population sensitivity shows how much the result changes when origins without a valid route are excluded.


In [9]:
accessibility_bar = (
    alt.Chart(report_results)
    .mark_bar(color=attaviz.SEQ_PURPLE[-2])
    .encode(
        x=alt.X(
            "threshold_minutes:O",
            title="Travel-time threshold (minutes)",
            sort=list(THRESHOLDS),
        ),
        y=alt.Y(
            "jobs_reachable_pct:Q",
            title="Modeled jobs reachable (%)",
            scale=alt.Scale(domain=[0, 100]),
        ),
        tooltip=[
            alt.Tooltip("threshold_minutes:O", title="Minutes"),
            alt.Tooltip(
                "jobs_reachable_pct:Q",
                title="All in-scope population",
                format=".2f",
            ),
            alt.Tooltip(
                "routed_population_jobs_reachable_pct:Q",
                title="Routed population",
                format=".2f",
            ),
        ],
    )
    .properties(
        title="Population-weighted access within the jobs layer",
        width=560,
        height=320,
    )
)
accessibility_labels = accessibility_bar.mark_text(
    align="center", baseline="bottom", dy=-6, color=attaviz.TEXT
).encode(text=alt.Text("jobs_reachable_pct:Q", format=".2f"))
display(
    attaviz.add_caption(
        accessibility_bar + accessibility_labels,
        "Missing matrix origins are zero-filled only in the conservative aggregate; see coverage status.",
    )
)

for threshold in THRESHOLDS:
    result_map = project_zone_accessibility.copy()
    result_map[f"jobs_reachable_{threshold}min_pct"] = result_map[
        f"accessibility_{threshold}min"
    ].where(result_map["has_any_route"])
    accessibility_explore = show_full_extent(
        simplify_for_web(result_map).explore(
            column=f"jobs_reachable_{threshold}min_pct",
            cmap="YlOrRd",
            legend=True,
            tooltip=[
                "zone_id",
                "tipo_zona",
                "population",
                "population_density_per_km2",
                "accessibility_15min",
                "accessibility_30min",
                "accessibility_45min",
                "routing_status",
            ],
            tiles=TILES,
            legend_kwds={"caption": f"Jobs reachable within {threshold} minutes (%)"},
            style_kwds={"weight": 0.35, "color": "white", "fillOpacity": 0.75},
            missing_kwds={
                "color": "lightgrey",
                "label": "No valid route in matrix",
            },
        )
    )
    display(accessibility_explore)


alt.VConcatChart(...)

## Jobs-layer hexagon accessibility

The cells below score only the baseline hex-to-hex matrix and display maps for the 15-, 30-, and 45-minute thresholds for Wednesday 08:00AM scenario.

In [10]:
baseline_hex_matrix_path = OUTPUT_PATH / "accessibility_grid_wed_08.parquet"
if not baseline_hex_matrix_path.exists():
    raise FileNotFoundError(baseline_hex_matrix_path)

baseline_hex_matrix = pd.read_parquet(baseline_hex_matrix_path)
baseline_hex_matrix[["from_id", "to_id"]] = baseline_hex_matrix[
    ["from_id", "to_id"]
].astype(str)
baseline_hex_ids = employment_grid["grid_id"].astype(str).tolist()
baseline_hex_scores = accessibility_scores(baseline_hex_matrix).rename(
    columns={"from_id": "grid_id"}
)
baseline_hex_coverage = routing_coverage(baseline_hex_matrix, baseline_hex_ids).rename(
    columns={"origin_id": "grid_id"}
)
hex_scores = employment_grid_local[
    ["grid_id", "pred_relative_employment", "geometry"]
].copy()
hex_scores["grid_id"] = hex_scores["grid_id"].astype(str)
hex_scores = hex_scores.merge(
    baseline_hex_scores, on="grid_id", how="left", validate="one_to_one"
).merge(
    baseline_hex_coverage[["grid_id", "routing_status"]],
    on="grid_id",
    how="left",
    validate="one_to_one",
)
assert (
    hex_scores["accessibility_15min"].fillna(0)
    <= hex_scores["accessibility_30min"].fillna(0)
).all()
assert (
    hex_scores["accessibility_30min"].fillna(0)
    <= hex_scores["accessibility_45min"].fillna(0)
).all()

/tmp/ipykernel_4412/2834447350.py:38: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  coverage["has_any_route"] = coverage["has_any_route"].fillna(False).astype(bool)


In [11]:
hex_map_data = simplify_for_web(hex_scores, tolerance=20)
for minutes in THRESHOLDS:
    column = f"accessibility_{minutes}min"
    hex_map = show_full_extent(
        hex_map_data.explore(
            column=column,
            cmap="YlOrRd",
            legend=True,
            tooltip=[
                "grid_id",
                "pred_relative_employment",
                "accessibility_15min",
                "accessibility_30min",
                "accessibility_45min",
                "routing_status",
            ],
            tiles=TILES,
            legend_kwds={
                "caption": f"Baseline Wednesday 08:00 jobs reachable within {minutes} minutes (percentage points)"
            },
            style_kwds={
                "weight": 0.2,
                "color": "#756bb1",
                "fillOpacity": 0.75,
            },
            missing_kwds={
                "color": "lightgrey",
                "label": "Origin missing from matrix",
            },
        )
    )
    display(hex_map)


## Neighborhood and census-section accessibility

In [ ]:
def include_if_overlapping_jobs_layer(frame):
    return frame.loc[frame.geometry.intersects(analysis_boundary)].copy()


barrios = (
    gpd.read_file(BARRIOS_PATH)
    .filter(["CODBARRIOINE", "NOMBARRIOINE", "geometry"])
    .to_crs(LOCAL_CRS)
)
barrios = include_if_overlapping_jobs_layer(barrios)

census_sections = (
    gpd.read_file(SECTIONS_PATH)
    .filter(["CODSECC", "SECC", "geometry"])
    .to_crs(LOCAL_CRS)
)
census_sections = include_if_overlapping_jobs_layer(census_sections)
census_sections["section_label"] = "Census section " + census_sections[
    "CODSECC"
].astype(str)


def build_admin_accessibility(targets, target_id_column, target_label_column):
    group_columns = [target_id_column, target_label_column]
    zone_source = project_zones[
        ["zone_id", "population", "zone_area_m2", "geometry"]
    ].copy()
    target_source = targets[group_columns + ["geometry"]].copy()
    intersections = gpd.overlay(
        zone_source, target_source, how="intersection", keep_geom_type=False
    )
    intersections["overlap_area_m2"] = intersections.geometry.area


    # TODO: Please review this code
    overlap_percentage = ((intersections.groupby('CODBARRIOINE').overlap_area_m2.sum())/targets.set_index('CODBARRIOINE').geometry.area)
    more_than_85 = overlap_percentage[overlap_percentage>.85].index
    intersections = barrios[barrios['CODBARRIOINE'].isin(more_than_85)].copy()
    # intersections = intersections.loc[intersections["overlap_area_m2"] > 0].copy()



    score_columns = [f"accessibility_{minutes}min" for minutes in THRESHOLDS]
    zone_metrics = project_zone_accessibility[
        ["zone_id", "matrix_row_coverage", "has_any_route", *score_columns]
    ]
    intersections = intersections.merge(
        zone_metrics, on="zone_id", how="left", validate="many_to_one"
    )
    

In [109]:
intersections

,zone_id,population,zone_area_m2,CODBARRIOINE,NOMBARRIOINE,geometry,overlap_area_m2,matrix_row_coverage,has_any_route,accessibility_15min,accessibility_30min,accessibility_45min
0,496,2060.0,1.503108e+07,1000016,BAÑADOS DE CARRASCO,GEOMETRYCOLLECTION (POLYGON ((581435.937 61429...,1.423267e+07,True,True,0.005331,0.014288,0.084305
1,490,1451.0,1.939321e+07,1000036,"CASABO, PAJAS BLANCAS",GEOMETRYCOLLECTION (POLYGON ((559385.695 61432...,9.518897e+06,True,True,0.001944,0.007914,0.018474
2,515,7600.0,8.381872e+06,1000061,"VILLA GARCIA, MANGA RUR.","POLYGON ((583307.022 6148251.463, 583299.666 6...",7.603710e+06,True,True,0.013482,0.056629,0.739502
3,517,287.0,1.238878e+07,1000016,BAÑADOS DE CARRASCO,"POLYGON ((584408.615 6146749.659, 584403.633 6...",7.134387e+06,True,True,0.004365,0.124481,2.203645
4,497,9882.0,6.794479e+06,1000061,"VILLA GARCIA, MANGA RUR.","POLYGON ((585735.598 6150316.347, 585695.732 6...",6.794479e+06,True,True,0.068529,0.831842,7.369853
...,...,...,...,...,...,...,...,...,...,...,...,...
958,193,1687.0,2.359008e+05,1020038,LA TEJA,GEOMETRYCOLLECTION (LINESTRING (569725.726 614...,0.000000e+00,True,True,0.796085,7.643136,44.184659
959,194,4853.0,5.329341e+05,1020038,LA TEJA,"MULTILINESTRING ((570242.471 6141947.8, 570168...",0.000000e+00,True,True,0.945567,7.562222,40.206199
960,196,2505.0,3.087592e+05,1020038,LA TEJA,"MULTIPOINT ((570917.535 6142605.019), (571111....",0.000000e+00,True,True,2.343871,21.763934,61.674237
961,342,1677.0,1.681219e+05,1020035,CERRO,"LINESTRING (567180.713 6139635.393, 567206.727...",0.000000e+00,True,True,0.234881,1.921747,9.220233


In [ ]:

intersections["target_population"] = (
    intersections["population"]
    * intersections["overlap_area_m2"]
    / intersections["zone_area_m2"]
)
intersections["missing_source_population"] = intersections["population"].isna()
intersections["missing_population_overlap_area_m2"] = intersections[
    "overlap_area_m2"
].where(intersections["missing_source_population"], 0)
intersections["missing_matrix_population"] = (
    intersections["target_population"]
    .where(~intersections["matrix_row_coverage"], 0)
    .fillna(0)
)
intersections["no_route_population"] = (
    intersections["target_population"]
    .where(
        intersections["matrix_row_coverage"] & ~intersections["has_any_route"],
        0,
    )
    .fillna(0)
)
intersections["routed_population"] = (
    intersections["target_population"]
    .where(intersections["has_any_route"], 0)
    .fillna(0)
)

for minutes in THRESHOLDS:
    score = intersections[f"accessibility_{minutes}min"].fillna(0)
    intersections[f"weighted_{minutes}min"] = (
        intersections["target_population"] * score
    )
    intersections[f"routed_weighted_{minutes}min"] = (
        intersections["routed_population"] * score
    )

population_summary = (
    intersections.groupby(group_columns, dropna=False)
    .agg(
        population=(
            "target_population",
            lambda values: values.sum(min_count=1),
        ),
        overlap_area_m2=("overlap_area_m2", "sum"),
        missing_population_overlap_area_m2=(
            "missing_population_overlap_area_m2",
            "sum",
        ),
        missing_matrix_population=("missing_matrix_population", "sum"),
        no_route_population=("no_route_population", "sum"),
        routed_population=("routed_population", "sum"),
    )
    .reset_index()
)
zone_status = intersections[
    group_columns
    + [
        "zone_id",
        "matrix_row_coverage",
        "has_any_route",
        "missing_source_population",
    ]
].drop_duplicates(subset=group_columns + ["zone_id"])
zone_status["missing_matrix_origin"] = ~zone_status["matrix_row_coverage"]
zone_status["has_no_route"] = (
    zone_status["matrix_row_coverage"] & ~zone_status["has_any_route"]
)
assert not (
    zone_status["missing_matrix_origin"] & zone_status["has_no_route"]
).any()
status_summary = (
    zone_status.groupby(group_columns, dropna=False)
    .agg(
        project_zone_overlaps=("zone_id", "nunique"),
        zones_with_any_route=("has_any_route", "sum"),
        zones_with_no_route=("has_no_route", "sum"),
        zones_missing_from_matrix=("missing_matrix_origin", "sum"),
        zones_with_missing_population=("missing_source_population", "sum"),
    )
    .reset_index()
)
summary = population_summary.merge(
    status_summary, on=group_columns, how="left", validate="one_to_one"
)

for minutes in THRESHOLDS:
    weighted = (
        intersections.groupby(group_columns, dropna=False)[f"weighted_{minutes}min"]
        .sum(min_count=1)
        .rename(f"weighted_{minutes}min_numerator")
    )
    routed_weighted = (
        intersections.groupby(group_columns, dropna=False)[
            f"routed_weighted_{minutes}min"
        ]
        .sum(min_count=1)
        .rename(f"routed_weighted_{minutes}min_numerator")
    )
    summary = summary.merge(
        weighted, on=group_columns, how="left", validate="one_to_one"
    ).merge(routed_weighted, on=group_columns, how="left", validate="one_to_one")
    summary[f"accessibility_{minutes}min_pct"] = (
        summary[f"weighted_{minutes}min_numerator"] / summary["population"]
    )
    summary[f"routed_accessibility_{minutes}min_pct"] = summary[
        f"routed_weighted_{minutes}min_numerator"
    ] / summary["routed_population"].replace(0, pd.NA)

output_columns = (
    group_columns
    + [
        "population",
        "routed_population",
        "missing_matrix_population",
        "no_route_population",
        "overlap_area_m2",
        "missing_population_overlap_area_m2",
        "project_zone_overlaps",
        "zones_with_any_route",
        "zones_with_no_route",
        "zones_missing_from_matrix",
        "zones_with_missing_population",
    ]
    + [f"accessibility_{minutes}min_pct" for minutes in THRESHOLDS]
    + [f"routed_accessibility_{minutes}min_pct" for minutes in THRESHOLDS]
)

In [61]:
barrios.explore()

In [56]:
# display(overall_accessibility.round(2))
# display(admin_coverage_diagnostics.round(2))
# display(neighborhood_accessibility.sort_values("population", ascending=False).round(2))
# display(
#     census_section_accessibility.sort_values("population", ascending=False).round(2)
# )

neighborhood_map_data = barrios.merge(
    neighborhood_accessibility,
    on=["CODBARRIOINE", "NOMBARRIOINE"],
    how="left",
    validate="one_to_one",
)
neighborhood_map = show_full_extent(
    simplify_for_web(neighborhood_map_data, tolerance=20).explore(
        column="accessibility_30min_pct",
        cmap="YlOrRd",
        legend=True,
        tooltip=[
            "CODBARRIOINE",
            "NOMBARRIOINE",
            "population",
            "accessibility_15min_pct",
            "accessibility_30min_pct",
            "accessibility_45min_pct",
            "missing_matrix_population",
            "no_route_population",
        ],
        tiles=TILES,
        legend_kwds={
            "caption": "Neighborhood population-weighted jobs reachable at 30 minutes (percentage points)"
        },
        style_kwds={"weight": 0.4, "color": "white", "fillOpacity": 0.75},
        missing_kwds={"color": "lightgrey", "label": "No population"},
    )
)
display(neighborhood_map)

section_map_data = census_sections.merge(
    census_section_accessibility,
    on=["CODSECC", "section_label"],
    how="left",
    validate="one_to_one",
)
section_map = show_full_extent(
    simplify_for_web(section_map_data, tolerance=20).explore(
        column="accessibility_30min_pct",
        cmap="YlGnBu",
        legend=True,
        tooltip=[
            "CODSECC",
            "section_label",
            "population",
            "accessibility_15min_pct",
            "accessibility_30min_pct",
            "accessibility_45min_pct",
            "missing_matrix_population",
            "no_route_population",
        ],
        tiles=TILES,
        legend_kwds={
            "caption": "Census-section population-weighted jobs reachable at 30 minutes (percentage points)"
        },
        style_kwds={"weight": 0.3, "color": "white", "fillOpacity": 0.75},
        missing_kwds={"color": "lightgrey", "label": "No population"},
    )
)
display(section_map)


NameError: name 'barrios' is not defined